In [31]:
import pandas as pd
import pickle as pkl
import numpy as np
import random
from tqdm import tqdm
from sklearn.model_selection import train_test_split
from sklearn.feature_extraction.text import HashingVectorizer
from sklearn.linear_model import SGDClassifier
from sklearn.model_selection import GridSearchCV
from sklearn import metrics
from sklearn.pipeline import Pipeline
from sklearn.base import BaseEstimator
from custom_models.custom_model import BatchVectorizerClassifier
from ray import tune
from sklearn.utils.multiclass import unique_labels
from sklearn.linear_model import SGDOneClassSVM

In [32]:
help(BatchVectorizerClassifier)

Help on class BatchVectorizerClassifier in module custom_models.custom_model:

class BatchVectorizerClassifier(builtins.object)
 |  BatchVectorizerClassifier(loss='hinge', penalty='l2', alpha=0.0001, l1_ratio=0.15, fit_intercept=True, max_iter=1000, tol=0.001, shuffle=True, verbose=0, epsilon=0.1, n_jobs=None, random_state=None, learning_rate='optimal', eta0=0.0, power_t=0.5, early_stopping=False, validation_fraction=0.1, n_iter_no_change=5, class_weight=None, warm_start=False, average=False)
 |  
 |  Custom vectorizer and classifier class to process data in
 |  batches.  Useful when there are RAM and CPU limitations.
 |  
 |  Args:
 |      BaseEstimator (Estimator): base class for estimator
 |  
 |  Methods defined here:
 |  
 |  __init__(self, loss='hinge', penalty='l2', alpha=0.0001, l1_ratio=0.15, fit_intercept=True, max_iter=1000, tol=0.001, shuffle=True, verbose=0, epsilon=0.1, n_jobs=None, random_state=None, learning_rate='optimal', eta0=0.0, power_t=0.5, early_stopping=False, v

In [33]:
BaseEstimator

sklearn.base.BaseEstimator

In [34]:
neg_to_pos_ratio = 1
seed = 42
batch_size = 100000

In [35]:
filename_pos_human = '../data/pubmed_articles_pos_human.csv'

pos_data_human = pd.read_csv(
         filename_pos_human,
            chunksize=100000
)


In [36]:
filename_neg_human = '../data/pubmed_articles_neg_human.csv'

neg_data_human = pd.read_csv(filename_neg_human, chunksize=100000)

In [37]:
with open('../data/cleaned_pos_neg_train_val_test_dataset_ids.pkl', 'rb') as f:
    prop_typ_id_dict= pkl.load(f)

In [38]:
prop_typ_id_dict.keys()

dict_keys(['is_rct', 'is_sr', 'is_casecontrol', 'is_ct', 'is_cohort', 'is_guideline', 'is_consensus', 'is_qual', 'is_ctprotocol'])

In [39]:
sr_pos_train_ids = prop_typ_id_dict['is_guideline']['pos']['train']
sr_neg_train_ids = prop_typ_id_dict['is_guideline']['neg']['train']

In [40]:
sr_pos_val_ids = prop_typ_id_dict['is_guideline']['pos']['val']
sr_neg_val_ids = prop_typ_id_dict['is_guideline']['neg']['val']

In [41]:
sr_pos_test_ids = prop_typ_id_dict['is_guideline']['pos']['test']
sr_neg_test_ids = prop_typ_id_dict['is_guideline']['neg']['test']

In [42]:
sr_pos_train_set = pd.DataFrame()
sr_pos_val_set = pd.DataFrame()
sr_pos_test_set = pd.DataFrame()

for pos_chunk in tqdm(pos_data_human):

    indices = pos_chunk.index
    indices = list(indices)
    
    
    pos_train_indices = list(set(indices).intersection(set(sr_pos_train_ids)))
    pos_val_indices = list(set(indices).intersection(set(sr_pos_val_ids)))
    pos_test_indices = list(set(indices).intersection(set(sr_pos_test_ids)))
    
    sr_pos_train_subset  = pos_chunk.loc[pos_train_indices]
    if sr_pos_train_set.empty:
        sr_pos_train_set = pd.DataFrame(columns = sr_pos_train_set.columns)
    sr_pos_train_set = pd.concat([sr_pos_train_set, sr_pos_train_subset])
    
    sr_pos_val_subset  = pos_chunk.loc[pos_val_indices]
    if sr_pos_val_set.empty:
        sr_pos_val_set = pd.DataFrame(columns = sr_pos_val_set.columns)
    sr_pos_val_set = pd.concat([sr_pos_val_set, sr_pos_val_subset])
    
    sr_pos_test_subset  = pos_chunk.loc[pos_test_indices]
    if sr_pos_test_set.empty:
        sr_pos_test_set = pd.DataFrame(columns = sr_pos_test_set.columns)
    sr_pos_test_set = pd.concat([sr_pos_test_set, sr_pos_test_subset])

sr_pos_train_set['is_guideline'] = int(1)
sr_pos_val_set['is_guideline'] = int(1)
sr_pos_test_set['is_guideline'] = int(1)

19it [00:25,  1.36s/it]/home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/tqdm/std.py:1195: DtypeWarning: Columns (14) have mixed types. Specify dtype option on import or set low_memory=False.
  for obj in iterable:
51it [01:07,  1.34s/it]/home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/tqdm/std.py:1195: DtypeWarning: Columns (14) have mixed types. Specify dtype option on import or set low_memory=False.
  for obj in iterable:
86it [01:54,  1.33s/it]


In [43]:
len(sr_pos_test_set)

1370

In [44]:
len(sr_pos_test_set)

1370

In [45]:
del pos_data_human
del sr_pos_train_subset 
del pos_chunk
del indices
del sr_pos_train_ids

In [46]:
sr_neg_train_ids_sample = random.sample(sr_neg_train_ids, round(len(sr_pos_train_set)*neg_to_pos_ratio))

In [47]:
sr_neg_train_set = pd.DataFrame()
sr_neg_val_set = pd.DataFrame()
sr_neg_test_set = pd.DataFrame()

for neg_chunk in tqdm(neg_data_human):

    indices = neg_chunk.index
    indices = list(indices)
    neg_train_indices = list(set(indices).intersection(set(sr_neg_train_ids_sample)))
    neg_val_indices = list(set(indices).intersection(set(sr_neg_val_ids)))
    neg_test_indices = list(set(indices).intersection(set(sr_neg_test_ids)))
    sr_neg_subset  = neg_chunk.loc[indices]
    
    
    sr_neg_train_subset  = neg_chunk.loc[neg_train_indices]
    if sr_neg_train_set.empty:
        sr_neg_train_set = pd.DataFrame(columns = sr_neg_train_set.columns)
    sr_neg_train_set = pd.concat([sr_neg_train_set, sr_neg_train_subset])
    
    sr_neg_val_subset  = neg_chunk.loc[neg_val_indices]
    if sr_neg_val_set.empty:
        sr_neg_val_set = pd.DataFrame(columns = sr_neg_val_set.columns)
    sr_neg_val_set = pd.concat([sr_neg_val_set, sr_neg_val_subset])
    
    sr_neg_test_subset  = neg_chunk.loc[neg_test_indices]
    if sr_neg_test_set.empty:
        sr_neg_test_set = pd.DataFrame(columns = sr_neg_test_set.columns)
    sr_neg_test_set = pd.concat([sr_neg_test_set, sr_neg_test_subset])

sr_neg_train_set['is_guideline'] = int(0)
sr_neg_val_set['is_guideline'] = int(0)
sr_neg_test_set['is_guideline'] = int(0)

57it [01:32,  1.62s/it]


In [48]:
len(sr_neg_test_set)

299825

In [49]:
sr_train_data = pd.concat([sr_neg_train_set, sr_pos_train_set]).sample(frac=1)

In [50]:
del sr_neg_train_set
del sr_pos_train_set

In [51]:
sr_val_data = pd.concat([sr_neg_val_set, sr_pos_val_set]).sample(frac=1)

In [52]:
del sr_neg_val_set
del sr_pos_val_set

In [53]:
sr_test_data = pd.concat([sr_neg_test_set, sr_pos_test_set]).sample(frac=1)

In [54]:
del sr_neg_test_set
del sr_pos_test_set

In [57]:
sr_train_data.columns

Index(['Unnamed: 0.1', 'index', 'Unnamed: 0', 'pmid', 'status',
       'indexing_method', 'title', 'abstract', 'abstract_plaintext', 'authors',
       'journal', 'journal_abbrv', 'year', 'mesh', 'month', 'volume', 'issue',
       'pages', 'ptyp', 'registry_ids', 'dois', 'is_guideline', 'unnamed: 0'],
      dtype='object')

In [25]:
# sr_data = sr_data.drop(columns = ['Unnamed: 0', 'unnamed: 0', 'indexing_method', 'abstract', 'journal_abbrv', 'year', 'mesh', 'month', 'volume', 'issue', 'pages',
#        'ptyp', 'registry_ids', 'dois',])

In [56]:
sr_train_data['title']

4834248    SOGC clinical practice guidelines: Adhesion pr...
434434     Effect of diaphragm and abdominal muscle train...
1466386    Validity, Reliability, and Inertia of Four Dif...
3632310    The 2016 Royal Australian and New Zealand Coll...
2096683    Treatment of severe Candida infections in high...
                                 ...                        
3676894    Aripiprazole in schizophrenia: consensus guide...
5078998    The (ir)relevance of procedural justice in the...
2344050    Pleomorphic hyalinizing angiectatic tumor of r...
3774043    Demystifying animal 'personality' (or not): wh...
2056763    Improvement of plant protein solubilization an...
Name: title, Length: 22188, dtype: object

In [60]:
sr_train_data['abstract_plaintext']

4834248    OBJECTIVES\n\n\nTo review the etiology and inc...
434434     Pelvic floor muscles (PFMs) play a crucial rol...
1466386    PURPOSE\n\n\nTelemetric temperature capsule sy...
3632310    INTRODUCTION\n\n\nThe Royal Australian and New...
2096683    Now that modern medicine can provide increasin...
                                 ...                        
3676894    Schizophrenia is a chronic disabling disease w...
5078998    Process-based approaches to compliance argue t...
2344050    Pleomorphic hyalinizing angiectatic tumor (PHA...
3774043    Animal 'personality', defined as repeatable in...
2056763    It is important to solubilize acetone-precipit...
Name: abstract_plaintext, Length: 22188, dtype: object

In [62]:
sr_train_data['title'][4834248]

'SOGC clinical practice guidelines: Adhesion prevention in gynaecological surgery: no. 243, June 2010.'

In [63]:
sr_train_data['abstract_plaintext'][4834248]

'OBJECTIVES\n\n\nTo review the etiology and incidence of and associative factors in the formation of adhesions following gynaecological surgery. To review evidence for the use of available means of adhesion prevention following gynaecological surgery.\nOPTIONS\n\n\nWomen undergoing pelvic surgery are at risk of developing abdominal and/or pelvic adhesive disease postoperatively. Surgical technique and commercial adhesion prevention systems may decrease the risk of postoperative adhesion formation.\nOUTCOMES\n\n\nThe outcomes measured are the incidence of postoperative adhesions, complications related to the formation of adhesions, and further intervention relative to adhesive disease.\nEVIDENCE\n\n\nMedline, EMBASE, and The Cochrane Library were searched for articles published in English from 1990 to March 2009, using appropriate controlled vocabulary and key words. Results were restricted to systematic reviews, randomized control trials/controlled clinical trials, cohort studies, and 

In [71]:
titles_abstracts = ["{0} {1}".format(title, abstract) for title, abstract in zip(sr_train_data['title'], sr_train_data['abstract_plaintext'])]

In [77]:
X_train = titles_abstracts

In [81]:
type(X_train)

list

In [74]:
y_train = sr_train_data['is_guideline']
# X_train = sr_train_data['abstract_plaintext']
# sr_inputs = sr_data['title'] + sr_data['abstract_plaintext']

In [75]:
y_val = sr_val_data['is_guideline']
# X_val = sr_val_data['abstract_plaintext']

In [76]:
y_test = sr_test_data['is_guideline']
# X_test = sr_test_data['abstract_plaintext']

In [88]:
num_batches =  5
X= pd.Series(X_train)
for X_chunk, y_chunk in zip(
            np.array_split(X, num_batches), np.array_split(y, num_batches)
        ):

            # convert text chunk to unicode
            X_chunk = X_chunk.values.astype("U")


In [86]:
type(X_chunk)

numpy.ndarray

In [78]:
bvc = BatchVectorizerClassifier(loss='hinge', penalty='l2', alpha=0.0001, l1_ratio=0.15, fit_intercept=True, max_iter=1000, tol=0.001, shuffle=True, verbose=0, epsilon=0.1, n_jobs=5, random_state=None, learning_rate='optimal', eta0=0.0, power_t=0.5, early_stopping=False, validation_fraction=0.1, n_iter_no_change=5, class_weight=None, warm_start=False, average=False)

In [79]:
bvc.fit(X_train, y_train)

AttributeError: 'numpy.ndarray' object has no attribute 'values'

In [28]:
del sr_train_data
del sr_val_data
del sr_test_data

In [30]:
# X_train, X_test_val, y_train, y_test_val =  train_test_split(sr_inputs, sr_labels, test_size=0.2)

In [31]:
# X_val, X_test, y_val, y_test =  train_test_split(X_test_val, y_test_val, test_size=0.5)

In [32]:
import os
os.path.join('model','pubmed_is_ct_trained_lr.pkl')

'model/pubmed_is_ct_trained_lr.pkl'

In [33]:
HashingVectorizer

sklearn.feature_extraction.text.HashingVectorizer

In [34]:
type(X_train)

pandas.core.series.Series

In [63]:
list(np.logspace(-10, -5, 20))

[1e-10,
 1.8329807108324374e-10,
 3.3598182862837877e-10,
 6.158482110660255e-10,
 1.1288378916846883e-09,
 2.06913808111479e-09,
 3.792690190732254e-09,
 6.951927961775591e-09,
 1.274274985703132e-08,
 2.3357214690901214e-08,
 4.281332398719396e-08,
 7.847599703514607e-08,
 1.438449888287663e-07,
 2.6366508987303554e-07,
 4.832930238571752e-07,
 8.858667904100833e-07,
 1.6237767391887209e-06,
 2.976351441631319e-06,
 5.455594781168514e-06,
 1e-05]

In [73]:
# vec = HashingVectorizer(ngram_range=(1, 4), stop_words='english')

# clf = SGDClassifier()

# bvc = BatchVectorizerClassifier(loss='hinge', penalty='l2', alpha=0.0001, l1_ratio=0.15, fit_intercept=True, max_iter=1000, tol=0.001, shuffle=True, verbose=0, epsilon=0.1, n_jobs=5, random_state=None, learning_rate='optimal', eta0=0.0, power_t=0.5, early_stopping=False, validation_fraction=0.1, n_iter_no_change=5, class_weight=None, warm_start=False, average=False)

config = {"loss": tune.grid_search(["log"]),
        "penalty": tune.grid_search(["l2", "l1", "elasticnet"]),
        "alpha": tune.grid_search(list(np.logspace(-10, -5, 20))),
#         "l1_ratio": tune.grid_search(list(np.linspace(0, 1, 20)))
         }



In [153]:
def objective(config, data):
    bvc = BatchVectorizerClassifier(loss=config['loss'], penalty=config['penalty'], alpha=config['alpha'], l1_ratio=0.15, fit_intercept=True, max_iter=1000, tol=0.001, shuffle=True, verbose=0, epsilon=0.1, n_jobs=None, random_state=None, learning_rate='optimal', eta0=0.0, power_t=0.5, early_stopping=False, validation_fraction=0.1, n_iter_no_change=5, class_weight=None, warm_start=False, average=False)
    bvc.fit(data['X_train'], data['y_train'])
    y_pred_val = bvc.predict(data['X_val'])
    f1 = metrics.f1_score(y_pred_val, data['y_val'])
    
    tune.report(f1=f1)
    
    return {"f1": f1}

In [154]:
data = {
    'X_train': X_train,
    'y_train': y_train,
    'X_val': X_val,
    'y_val': y_val
}

In [155]:
analysis = tune.run(tune.with_parameters(objective, data = data), config=config, resources_per_trial={'gpu': 1}, verbose = 3)

2022-06-25 15:26:47,622	INFO trial_runner.py:803 -- starting objective_d869c_00000


Trial name,status,loc,alpha,loss,penalty
objective_d869c_00000,RUNNING,10.151.122.12:66800,1e-10,log,l2
objective_d869c_00001,PENDING,,1.83298e-10,log,l2
objective_d869c_00002,PENDING,,3.35982e-10,log,l2
objective_d869c_00003,PENDING,,6.15848e-10,log,l2
objective_d869c_00004,PENDING,,1.12884e-09,log,l2
objective_d869c_00005,PENDING,,2.06914e-09,log,l2
objective_d869c_00006,PENDING,,3.79269e-09,log,l2
objective_d869c_00007,PENDING,,6.95193e-09,log,l2
objective_d869c_00008,PENDING,,1.27427e-08,log,l2
objective_d869c_00009,PENDING,,2.33572e-08,log,l2


Trial name,status,loc,alpha,loss,penalty
objective_d869c_00000,RUNNING,10.151.122.12:66800,1e-10,log,l2
objective_d869c_00001,PENDING,,1.83298e-10,log,l2
objective_d869c_00002,PENDING,,3.35982e-10,log,l2
objective_d869c_00003,PENDING,,6.15848e-10,log,l2
objective_d869c_00004,PENDING,,1.12884e-09,log,l2
objective_d869c_00005,PENDING,,2.06914e-09,log,l2
objective_d869c_00006,PENDING,,3.79269e-09,log,l2
objective_d869c_00007,PENDING,,6.95193e-09,log,l2
objective_d869c_00008,PENDING,,1.27427e-08,log,l2
objective_d869c_00009,PENDING,,2.33572e-08,log,l2


Trial name,status,loc,alpha,loss,penalty
objective_d869c_00000,RUNNING,10.151.122.12:66800,1e-10,log,l2
objective_d869c_00001,PENDING,,1.83298e-10,log,l2
objective_d869c_00002,PENDING,,3.35982e-10,log,l2
objective_d869c_00003,PENDING,,6.15848e-10,log,l2
objective_d869c_00004,PENDING,,1.12884e-09,log,l2
objective_d869c_00005,PENDING,,2.06914e-09,log,l2
objective_d869c_00006,PENDING,,3.79269e-09,log,l2
objective_d869c_00007,PENDING,,6.95193e-09,log,l2
objective_d869c_00008,PENDING,,1.27427e-08,log,l2
objective_d869c_00009,PENDING,,2.33572e-08,log,l2


Trial name,status,loc,alpha,loss,penalty
objective_d869c_00000,RUNNING,10.151.122.12:66800,1e-10,log,l2
objective_d869c_00001,PENDING,,1.83298e-10,log,l2
objective_d869c_00002,PENDING,,3.35982e-10,log,l2
objective_d869c_00003,PENDING,,6.15848e-10,log,l2
objective_d869c_00004,PENDING,,1.12884e-09,log,l2
objective_d869c_00005,PENDING,,2.06914e-09,log,l2
objective_d869c_00006,PENDING,,3.79269e-09,log,l2
objective_d869c_00007,PENDING,,6.95193e-09,log,l2
objective_d869c_00008,PENDING,,1.27427e-08,log,l2
objective_d869c_00009,PENDING,,2.33572e-08,log,l2


...

Trial name,status,loc,alpha,loss,penalty,iter,total time (s),f1
objective_d869c_00059,RUNNING,10.151.122.12:71475,1e-05,log,elasticnet,,,
objective_d869c_00000,TERMINATED,10.151.122.12:66800,1e-10,log,l2,1,168.449,0.526847
objective_d869c_00001,TERMINATED,10.151.122.12:66869,1.83298e-10,log,l2,1,169.067,0.565032
objective_d869c_00002,TERMINATED,10.151.122.12:66984,3.35982e-10,log,l2,1,181.536,0.535955
objective_d869c_00003,TERMINATED,10.151.122.12:67063,6.15848e-10,log,l2,1,181.478,0.548335
objective_d869c_00004,TERMINATED,10.151.122.12:67133,1.12884e-09,log,l2,1,181.6,0.55791
objective_d869c_00005,TERMINATED,10.151.122.12:67205,2.06914e-09,log,l2,1,182.059,0.512373
objective_d869c_00006,TERMINATED,10.151.122.12:67278,3.79269e-09,log,l2,1,181.731,0.57292
objective_d869c_00007,TERMINATED,10.151.122.12:67352,6.95193e-09,log,l2,1,183.22,0.572105
objective_d869c_00008,TERMINATED,10.151.122.12:67426,1.27427e-08,log,l2,1,181.565,0.515494


Trial name,status,loc,alpha,loss,penalty,iter,total time (s),f1
objective_d869c_00059,RUNNING,10.151.122.12:71475,1e-05,log,elasticnet,,,
objective_d869c_00000,TERMINATED,10.151.122.12:66800,1e-10,log,l2,1,168.449,0.526847
objective_d869c_00001,TERMINATED,10.151.122.12:66869,1.83298e-10,log,l2,1,169.067,0.565032
objective_d869c_00002,TERMINATED,10.151.122.12:66984,3.35982e-10,log,l2,1,181.536,0.535955
objective_d869c_00003,TERMINATED,10.151.122.12:67063,6.15848e-10,log,l2,1,181.478,0.548335
objective_d869c_00004,TERMINATED,10.151.122.12:67133,1.12884e-09,log,l2,1,181.6,0.55791
objective_d869c_00005,TERMINATED,10.151.122.12:67205,2.06914e-09,log,l2,1,182.059,0.512373
objective_d869c_00006,TERMINATED,10.151.122.12:67278,3.79269e-09,log,l2,1,181.731,0.57292
objective_d869c_00007,TERMINATED,10.151.122.12:67352,6.95193e-09,log,l2,1,183.22,0.572105
objective_d869c_00008,TERMINATED,10.151.122.12:67426,1.27427e-08,log,l2,1,181.565,0.515494


Result for objective_d869c_00059:
  date: 2022-06-25_18-32-15
  done: false
  experiment_id: 84a783dfd5034e1d854e2acbb48a5d8a
  f1: 0.612600422832981
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 71475
  time_since_restore: 182.99987173080444
  time_this_iter_s: 182.99987173080444
  time_total_s: 182.99987173080444
  timestamp: 1656178335
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: d869c_00059
  warmup_time: 0.0016872882843017578
  
Result for objective_d869c_00059:
  date: 2022-06-25_18-32-15
  done: true
  experiment_id: 84a783dfd5034e1d854e2acbb48a5d8a
  experiment_tag: 59_alpha=1e-05,loss=log,penalty=elasticnet
  f1: 0.612600422832981
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 71475
  time_since_restore: 182.99987173080444
  time_this_iter_s: 182.99987173080444
  time_total_s: 182.99987173080444
  timestamp: 1656178335
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: d869

Trial name,status,loc,alpha,loss,penalty,iter,total time (s),f1
objective_d869c_00000,TERMINATED,10.151.122.12:66800,1e-10,log,l2,1,168.449,0.526847
objective_d869c_00001,TERMINATED,10.151.122.12:66869,1.83298e-10,log,l2,1,169.067,0.565032
objective_d869c_00002,TERMINATED,10.151.122.12:66984,3.35982e-10,log,l2,1,181.536,0.535955
objective_d869c_00003,TERMINATED,10.151.122.12:67063,6.15848e-10,log,l2,1,181.478,0.548335
objective_d869c_00004,TERMINATED,10.151.122.12:67133,1.12884e-09,log,l2,1,181.6,0.55791
objective_d869c_00005,TERMINATED,10.151.122.12:67205,2.06914e-09,log,l2,1,182.059,0.512373
objective_d869c_00006,TERMINATED,10.151.122.12:67278,3.79269e-09,log,l2,1,181.731,0.57292
objective_d869c_00007,TERMINATED,10.151.122.12:67352,6.95193e-09,log,l2,1,183.22,0.572105
objective_d869c_00008,TERMINATED,10.151.122.12:67426,1.27427e-08,log,l2,1,181.565,0.515494
objective_d869c_00009,TERMINATED,10.151.122.12:67510,2.33572e-08,log,l2,1,181.784,0.566581


2022-06-25 18:32:15,955	INFO tune.py:701 -- Total run time: 11128.47 seconds (11128.35 seconds for the tuning loop).


In [156]:
print(analysis.get_best_config(metric="f1", mode="max"))

{'loss': 'log', 'penalty': 'l1', 'alpha': 8.858667904100833e-07}


In [161]:
best_config = analysis.get_best_config(metric="f1", mode="max")

In [163]:
bvc = BatchVectorizerClassifier(loss=best_config['loss'], penalty=best_config['penalty'], alpha=best_config['alpha'], l1_ratio=0.15, fit_intercept=True, max_iter=1000, tol=0.001, shuffle=True, verbose=0, epsilon=0.1, n_jobs=None, random_state=None, learning_rate='optimal', eta0=0.0, power_t=0.5, early_stopping=False, validation_fraction=0.1, n_iter_no_change=5, class_weight=None, warm_start=False, average=False)
bvc.fit(data['X_train'], data['y_train'])

In [164]:
y_pred_val = bvc.predict(data['X_val'])
f1_val = metrics.f1_score(y_pred_val, data['y_val'])
f1_val

0.6261272867817573

In [167]:
y_pred_test = bvc.predict(X_test)
f1_test = metrics.f1_score(y_pred_test, y_test)
f1_test

0.6268279689997078

In [177]:
len(X_test)

333447

In [178]:
len(X_val)

300102

In [169]:
best_trial = analysis.get_best_trial(metric="f1", mode="max", scope="all") 
# Gets best checkpoint for trial based on accuracy.
best_checkpoint = analysis.get_best_checkpoint(best_trial, metric="f1", mode="max")

2022-06-25 19:02:12,313	ERROR experiment_analysis.py:450 -- No checkpoints have been found for trial objective_d869c_00035.


In [172]:
# 1. Define an objective function.
def small_objective(config):
    score = config["a"] ** 2 + config["b"]
    return {"f1": score}


# 2. Define a search space.
search_space = {
#     "a": tune.grid_search([0.001, 0.01, 0.1, 1.0]),
    "a": tune.grid_search(list(np.logspace(-10, -5, 20))),
    "b": tune.choice([1, 2, 3]),
}

# 3. Start a Tune run and print the best result.
small_analysis = tune.run(small_objective, config=search_space, keep_checkpoints_num=1,checkpoint_freq=1, checkpoint_score_attr="f1")
print(small_analysis.get_best_config(metric="f1", mode="max"))

2022-06-25 19:04:06,260	WARNING tune.py:636 -- Tune detects GPUs, but no trials are using GPUs. To enable trials to use GPUs, set tune.run(resources_per_trial={'gpu': 1}...) which allows Tune to expose 1 GPU to each trial. You can also override `Trainable.default_resource_request` if using the Trainable API.
2022-06-25 19:04:06,420	INFO trial_runner.py:803 -- starting small_objective_34203_00000


Trial name,status,loc,a,b
small_objective_34203_00000,RUNNING,10.151.122.12:72754,1e-10,1
small_objective_34203_00001,PENDING,,1.83298e-10,2
small_objective_34203_00002,PENDING,,3.35982e-10,2
small_objective_34203_00003,PENDING,,6.15848e-10,1
small_objective_34203_00004,PENDING,,1.12884e-09,2
small_objective_34203_00005,PENDING,,2.06914e-09,1
small_objective_34203_00006,PENDING,,3.79269e-09,2
small_objective_34203_00007,PENDING,,6.95193e-09,3
small_objective_34203_00008,PENDING,,1.27427e-08,3
small_objective_34203_00009,PENDING,,2.33572e-08,2


2022-06-25 19:04:07,227	INFO trial_runner.py:803 -- starting small_objective_34203_00001
2022-06-25 19:04:07,240	INFO trial_runner.py:803 -- starting small_objective_34203_00002
2022-06-25 19:04:07,244	INFO trial_runner.py:803 -- starting small_objective_34203_00003
2022-06-25 19:04:07,247	INFO trial_runner.py:803 -- starting small_objective_34203_00004
2022-06-25 19:04:07,250	INFO trial_runner.py:803 -- starting small_objective_34203_00005
2022-06-25 19:04:07,254	INFO trial_runner.py:803 -- starting small_objective_34203_00006
2022-06-25 19:04:07,257	INFO trial_runner.py:803 -- starting small_objective_34203_00007
2022-06-25 19:04:07,262	INFO trial_runner.py:803 -- starting small_objective_34203_00008
2022-06-25 19:04:07,266	INFO trial_runner.py:803 -- starting small_objective_34203_00009
2022-06-25 19:04:07,269	INFO trial_runner.py:803 -- starting small_objective_34203_00010
2022-06-25 19:04:07,274	INFO trial_runner.py:803 -- starting small_objective_34203_00011
2022-06-25 19:04:07,2

Result for small_objective_34203_00000:
  date: 2022-06-25_19-04-07
  done: false
  experiment_id: 417f98413a2d48c1a5a137cebc752475
  f1: 1.0
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 72754
  time_since_restore: 0.00015544891357421875
  time_this_iter_s: 0.00015544891357421875
  time_total_s: 0.00015544891357421875
  timestamp: 1656180247
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: '34203_00000'
  warmup_time: 0.0016486644744873047
  
Result for small_objective_34203_00000:
  date: 2022-06-25_19-04-07
  done: true
  experiment_id: 417f98413a2d48c1a5a137cebc752475
  experiment_tag: 0_a=1e-10,b=1
  f1: 1.0
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 72754
  time_since_restore: 0.00015544891357421875
  time_this_iter_s: 0.00015544891357421875
  time_total_s: 0.00015544891357421875
  timestamp: 1656180247
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: '34203_00000'
  warmup_

2022-06-25 19:04:07,906	INFO trial_runner.py:803 -- starting small_objective_34203_00016


...

2022-06-25 19:04:09,239	INFO trial_runner.py:803 -- starting small_objective_34203_00019


Result for small_objective_34203_00016:
  date: 2022-06-25_19-04-09
  done: false
  experiment_id: a1d77581a7f241b983c1e6da92def26c
  f1: 3.0000000000026366
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 72871
  time_since_restore: 0.00014662742614746094
  time_this_iter_s: 0.00014662742614746094
  time_total_s: 0.00014662742614746094
  timestamp: 1656180249
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: '34203_00016'
  warmup_time: 0.0019268989562988281
  
Result for small_objective_34203_00016:
  date: 2022-06-25_19-04-09
  done: true
  experiment_id: a1d77581a7f241b983c1e6da92def26c
  experiment_tag: 16_a=1.6238e-06,b=3
  f1: 3.0000000000026366
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 72871
  time_since_restore: 0.00014662742614746094
  time_this_iter_s: 0.00014662742614746094
  time_total_s: 0.00014662742614746094
  timestamp: 1656180249
  timesteps_since_restore: 0
  training_iteration: 1

Trial name,status,loc,a,b,iter,total time (s),f1
small_objective_34203_00000,TERMINATED,10.151.122.12:72754,1e-10,1,1,0.000155449,1
small_objective_34203_00001,TERMINATED,10.151.122.12:72786,1.83298e-10,2,1,0.000201941,2
small_objective_34203_00002,TERMINATED,10.151.122.12:72788,3.35982e-10,2,1,0.000259876,2
small_objective_34203_00003,TERMINATED,10.151.122.12:72790,6.15848e-10,1,1,0.000194311,1
small_objective_34203_00004,TERMINATED,10.151.122.12:72792,1.12884e-09,2,1,0.000247478,2
small_objective_34203_00005,TERMINATED,10.151.122.12:72794,2.06914e-09,1,1,0.000171185,1
small_objective_34203_00006,TERMINATED,10.151.122.12:72796,3.79269e-09,2,1,0.000189304,2
small_objective_34203_00007,TERMINATED,10.151.122.12:72799,6.95193e-09,3,1,0.000326395,3
small_objective_34203_00008,TERMINATED,10.151.122.12:72802,1.27427e-08,3,1,0.000166893,3
small_objective_34203_00009,TERMINATED,10.151.122.12:72804,2.33572e-08,2,1,0.000192165,2


2022-06-25 19:04:10,165	INFO tune.py:701 -- Total run time: 3.92 seconds (3.78 seconds for the tuning loop).


{'a': 1.6237767391887209e-06, 'b': 3}


In [173]:
best_trial = small_analysis.get_best_trial(metric="f1", mode="max", scope="all") 
# Gets best checkpoint for trial based on accuracy.
best_checkpoint = small_analysis.get_best_checkpoint(best_trial, metric="f1", mode="max")

In [174]:
best_checkpoint

<TrialCheckpoint local_path=/home/k2141255/ray_results/small_objective_2022-06-25_19-04-06/small_objective_34203_00016_16_a=1.6238e-06,b=3_2022-06-25_19-04-07/checkpoint_-00001/, cloud_path=None>

In [176]:
!ls /home/k2141255/ray_results/small_objective_2022-06-25_19-04-06/small_objective_34203_00016_16_a=1.6238e-06,b=3_2022-06-25_19-04-07/checkpoint_-00001/

In [ ]:
with open('model/pubmed_is_ct_trained_lr.pck', 'wb') as f:
    pkl.dump(clf.best_estimator_, f)

In [ ]:
X_test_trans = vec.transform(X_test.values.astype('U'))
preds = clf.predict_proba(X_test_trans)

In [ ]:
preds = clf.predict_proba(X_test.values.astype('U'))

In [ ]:
preds

In [ ]:
metrics.plot_roc_curve(clf, X_test_trans, y_test) 

In [ ]:
y_pred = clf.predict(X_test_trans)

In [ ]:
y_pred

In [ ]:
metrics.precision_score(y_pred, y_test)

In [ ]:
metrics.recall_score(y_pred, y_test)

In [ ]:
metrics.f1_score(y_pred, y_test)

In [ ]:
metrics.accuracy_score(y_pred, y_test)

In [ ]:
len(y_test)